# 13 -- Animals: goose/egg lifecycle

Animals are the biggest unbuilt lever left (`PROGRESS.md`, Next steps):
the v5 replay (`97648603`) showed the opponent running `COW`/`MILK` and
`SHEEP`/`WOOL` plus direct `FERTILIZER` sales, income streams we have
none of.

Starting with **goose/egg** rather than cow or sheep (see chat design
discussion): cheapest to buy ($300 vs $400/$500), fastest first yield
(day 4 vs day 8/6), and simplest production cadence -- eggs are produced
every day once fed, so there's no "every N days" interval bookkeeping to
get right before the rest of the mechanism (`FEED`/`HARVEST`/`CARE`/
`COLLECT_FERTILIZER`) is validated. `COOP` and `PASTURE` are structurally
the same kind of thing, so this should generalize to cow/sheep afterward
by parametrizing the structure type and the production interval.

Plan, in increments (each validated before moving to the next):
1. **Mini-test**: confirm the real shape of a `COOP` tile and a placed
   animal's fields on an actual `obs`, not just from `README.md`.
2. **Get a live goose on the coop**: `BUY_ANIMAL` -> `PICKUP` ->
   `BUILD_COOP` -> `PLACE`, nothing else yet (no `FEED`/`HARVEST`).
3. Layer in `FEED`, `HARVEST`, `CARE`, `COLLECT_FERTILIZER`, and selling
   `EGG`/`FERTILIZER`.
4. Generalize to `COW`/`SHEEP` (pasture, interval-based production).


In [1]:
import sys
from pathlib import Path

from kaggle_environments import make

sys.path.insert(0, str(Path.cwd().parent / "src"))

from kaggriculture_bot.evaluate import evaluate
from kaggriculture_bot.strategies.baseline import melon_then_wheat_extra_hands_agent


## Mini-test: confirm `COOP` / animal tile shape on a real `obs`

Same pattern as notebook 11's `_test_buy_land_agent`: a throwaway agent
that just does `BUILD_COOP` (and later `BUY_ANIMAL`/`PICKUP`/`PLACE`) and
otherwise passes, run directly against `test_env`, then inspect the
resulting tile dict and shed/inventory fields on the real `obs` -- don't
assume the README's documented shape matches without checking.


In [11]:
def _test_goose_agent(obs):
    market = []
    if obs["step"] == 0:
        market.append(["BUY_ANIMAL", "GOOSE", 1])
    farmer = []

    farmer_pos = obs["farms"][obs["player"]]["farmer"]
    x, y = farmer_pos
    tile = obs["farms"][obs["player"]]["tiles"][y][x]

    if tile is None:
        farmer = ["BUILD_COOP"]
    elif tile is not None and tile.get("kind") == "COOP" and obs["private"]["inventories"][0].get("GOOSE", 0) == 0:
        farmer = ["PICKUP", "GOOSE", 1]
    elif tile is not None and tile.get("kind") == "COOP" and obs["private"]["inventories"][0].get("GOOSE", 0) > 0:
            farmer = ["PLACE", "GOOSE", 1]
    return {"farmer": farmer, "hands": [], "market": market}


test_env = make("kaggriculture", configuration={"episodeSteps": 720}, debug=True)
test_env.run([_test_goose_agent, "random"])

[[{'action': {'farmer': ['PASS'], 'hands': [], 'market': []},
   'reward': 0,
   'info': {},
   'observation': {'remainingOverageTime': 60,
    'step': 0,
    'player': 0,
    'farms': [{'money': 3000.0,
      'tiles': [[None,
        None,
        None,
        None,
        None,
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED'],
       [None,
        None,
        None,
        None,
        None,
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED'],
       [None,
        None,
        None,
        None,
        None,
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED'],
       [None,
        None,
        None,
        None,
        None,
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED'],
       [None,
        None,
        None,
        None,
        None,
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED',
 

In [ ]:
prev = None
for i, step in enumerate(test_env.steps):
    obs = step[0]["observation"]
    farm = obs["farms"][obs["player"]]
    x, y = farm["farmer"]
    tile = farm["tiles"][y][x]
    shed_goose = obs["private"]["shed"].get("GOOSE", 0)
    inv_goose = obs["private"]["inventories"][0].get("GOOSE", 0)
    snapshot = (tile, shed_goose, inv_goose)
    if snapshot != prev:
        print(i, "tile:", tile, "| shed GOOSE:", shed_goose, "| farmer inv GOOSE:", inv_goose)
        prev = snapshot


## Building the goose lifecycle agent

Your turn -- the sequence agreed in chat: `BUY_ANIMAL` -> `PICKUP` ->
`BUILD_COOP` -> `PLACE`, decided fresh each turn from `obs` (not a fixed
script), same reactive style as the crop-tending branches in
`melon_then_wheat_extra_hands_agent`.


## Validate

Current best is `melon_then_wheat_extra_hands_agent`. Decide what
"validated" means for this increment -- no eggs are sold yet, so a
win/loss `evaluate()` comparison may not be the right check until
`FEED`/`HARVEST`/selling exist. Confirming directly on `obs` that the
goose ends up alive on the coop may be enough for now.
